(population-displacement-estimation)=
# Estimating Population Displacement based on Mobility Data

In this exploratory analysis, we aim to estimate the location and dwelling period in Lebanon of GPS-devices seen previously in Syria. 

```{important}
This documentation outlines an **experimental** and **exploratory** process of creating such maps using mobility data. While this approach may address data scarcity, offer timeliness and other advantages, the results are not exempt from important {ref}`population-density-estimation-limitations`.
```

In [38]:
import dask.dataframe as dd
import geopandas
import humanize
import pandas as pd

## Data

### Area of Interest

In this explotatory analysis, we employ the [Lebanon's subnational administrative boundaries](https://data.humdata.org/m/dataset/cod-ab-lbn) maintained by [UNOCHA Middle East and North Africa (ROMENA)](https://data.humdata.org/m/organization/ae50792c-b87d-46bb-b42f-3887264ce019?) on the [Humanitarian Data Exchange](https://data.humdata.org/).

In [39]:
LBN = geopandas.read_file(
    "../../data/shapefiles/lbn_adm_cdr_20200810/lbn_admbnda_adm3_cdr_20200810.shp",
    crs="EPSG:4326",
)

In [40]:
LBN.explore(style_kwds={"weight": 0.75, "fillOpacity": 0.25})

### Mobility Data

Through the [Development Data Partnership](https://datapartnership.org), the project team obtained a longitudinal panel of human mobility. The panel consisted anonymized timestamped geographical points generated by GPS-enabled devices, located in Syria spanning the period between **January 1, 2020** to **August 31, 2023**.

The mobility data panel was provided pro-bono by [Veraset](https://www.veraset.com/) to the proposal [Understanding Lebanon's Economy through Alternative Data](https://portal.datapartnership.org/readableproposal/478) through the [Development Data Partnership](https://datapartnership.org). During the project’s execution, Veraset Movement’s global daily data feed was ingested and processed through the [Geolocation Data Pipeline](https://docs.datapartnership.org/collections/mobility/docs/geolocation-data/README.html#geolocation-data-pipeline) maintained by the Development Data Partnership. For additional information, please refer to the [Mobility Documentation](https://docs.datapartnership.org/collections/mobility/README.html) accessible to all World Bank staff.


In [9]:
ddf = dd.read_parquet(
    "../../data/interim/panels/v2023.9.4",
    filters=[("country", "=", "SY")],
    dtype_backend="pyarrow",
)

#### Determining panel of devices seen in Syria

From the mobility data panel, we select a (sub) panel of devices. This panel will be composed by the set of devices seen in Syria during the periods of: January/2020, July/2020, January/2021, July/2021, January/2022, July/2022 and January-August/2023.

In [50]:
DEVICES_SYR = ddf["uid"].unique().compute()

#### Importing Stay Locations in Lebanon

Based on {ref}`population-density-estimation`, we import the **stay locations** in Lebanon for the period of **August 1, 2023** to **August 31, 2023**.

In [52]:
STOPS = pd.read_parquet("../../data/locations.pq")

Now, we select only **stay locations** of devices that are in the panel of devices that were detected in Syria.

In [54]:
STOPS = STOPS[STOPS["uid"].isin(DEVICES_SYR["uid"])]

In [55]:
print("Number of stay locations:", humanize.intcomma(len(STOPS)))

Number of stay locations: 3,391


## Methodology

The methodology is second take on {ref}`population-density-estimation`, looking specifically at the panel of devices detected in Syria. For additional details, please refer to that reference. 

```{seealso}
{ref}`population-density-estimation`,
```

## Implementation

In [66]:
locations = STOPS[(STOPS["isHome"]) & (STOPS["home_delta_count"] > 0.25)]

In [67]:
print(f"Number of eligible devices: {humanize.intcomma(len(locations))}")

Number of eligible devices: 170


Now, let's get transform the home locations into a (sample) population density at administrative boundaries. 

In [68]:
locations = geopandas.GeoDataFrame(
    locations,
    geometry=geopandas.points_from_xy(locations["lng_medoid"], locations["lat_medoid"]),
    crs="EPSG:4326",
)

DENSITY_LOCATIONS = geopandas.GeoDataFrame(
    locations.sjoin(LBN, predicate="within")
    .groupby(["admin3Pcod"])["uid"]
    .count()
    .to_frame("count")
    .merge(LBN, on="admin3Pcod"),
    geometry="geometry",
    crs="EPSG:4326",
)

And finally mapping, 

In [72]:
DENSITY_LOCATIONS[["count", "geometry"]].dropna(subset="geometry").explore(
    column="count",
    cmap="plasma",
    style_kwds={"weight": 0.4},
    legend_kwds={"max_labels": 5},
    vmin=1,
    vmax=DENSITY_LOCATIONS["count"].max(),
)

> Estimated dwelling locations of devices detected in Syria previously (2020-2023). The metrics are present in reference to the month August/2023 in Lebanon. Source: Veraset Movement.  

## Findings

- The analysis identified potential $170$ dwelling locations of devices previously detected in Syria in reference to the month August/2023 in Lebanon. 

- Even though this approach may address data scarcity, offer timeliness and other advantages, the results suffer from significant limitations, including coarse sample size, sample bias and incomplete coverage. 

## Limitations

```{caution}

- **Sample Bias:** The sampled population is composed of GPS-enabled devices drawn out from a longituginal mobility data panel. It is important to emphasize the sampled population is obtained via convenience sampling and that the mobility data panel represents only a subset of the total population in an area at a time, specifically only users that turned on location tracking on their mobile device. Thus, derived metrics do not represent the total population density.

- **Incomplete Coverage:** Mobility data is typically collected from sources such as mobile phone networks, GPS devices, or transportation systems. These sources may not be representative of the entire population or all economic activities, leading to sample bias and potentially inaccurate estimations.Not all individuals or businesses have access to devices or services that generate mobility data. This can result in incomplete coverage and potential underrepresentation of certain demographic groups or economic sectors.

- **Lack of Contextual Information:** Mobility data primarily captures movement patterns and geolocation information. It may lack other crucial contextual information, which are essential for accurate estimation of economic activity.
```